In [1]:
import numpy as np

from IPython.display import display, Audio # play audio
import soundfile as sf # read n write audio
import wave # dataset audio .wav
from pydub import AudioSegment # audio editing
import librosa # audio effects

import torch, torchaudio

c:\Anaconda3\envs\speech_recognition\lib\site-packages\pydub\utils.py:170: RuntimeWarning: Couldn't find ffmpeg or avconv - defaulting to ffmpeg, but may not work
  warn("Couldn't find ffmpeg or avconv - defaulting to ffmpeg, but may not work", RuntimeWarning)


In [2]:
AUDIO_FILE = 'sample.wav'

In [3]:
# audio component
# sample rate -> ada beberapa samples per seconds, 16000 Hz = 16000 number
# sample width -> bytes per sample
# Duration -> number of sample

data, sr = sf.read(AUDIO_FILE)
print('Sample Rate : ', sr)
print('Sample : ', len(data))
print('Duration : ', len(data)/sr)
print('First 5 data : ', data[:5])

Sample Rate :  16000
Sample :  480000
Duration :  30.0
First 5 data :  [ 4.27246094e-04  3.05175781e-05 -1.83105469e-04  6.10351562e-05
 -9.15527344e-05]


In [4]:
# display audio
display(Audio(AUDIO_FILE))

In [5]:
# write and read
data, sr = sf.read(AUDIO_FILE)
sf.write('new_file.flac', data, sr)

FILE_FLAC = 'new_file.flac'
display(Audio(FILE_FLAC))

In [6]:
# read file info and write
obj = wave.open(AUDIO_FILE, 'r')
print('Channel : ', obj.getnchannels())
print('Sample Width : ', obj.getsampwidth())
print('Frame Rate : ', obj.getframerate())
print('Frame : ', obj.getnframes())

# store params and frames
params = obj.getparams()
frames = obj.readframes(obj.getnframes())
obj.close()

# write
obj = wave.open('new_wave.wav', 'w')
obj.setparams(params)
obj.writeframes(frames)
obj.close()



Channel :  1
Sample Width :  2
Frame Rate :  16000
Frame :  480000


In [7]:
# pydubload, cut, export
sound = AudioSegment.from_wav(AUDIO_FILE)
print('Duration (ms) : ', len(sound))

# cut duration audio
first_5s = sound[:5000]
first_5s.export('first_5s.wav', format='wav')
display(Audio('first_5s.wav'))

Duration (ms) :  30000


In [11]:
signal, sr = torchaudio.load(AUDIO_FILE)
print('Sample Rate : ', sr)

Sample Rate :  16000


In [14]:
# shape (channels, samples)
waveform = torch.tensor(signal).unsqueeze(0)
print('Shape : ', waveform.shape)

# change sample rate from 16k to 8k
waverform_8k = torchaudio.transforms.Resample(sr, 8000)(waveform)

print('new sr : ', waverform_8k.shape)

Shape :  torch.Size([1, 1, 480000])
new sr :  torch.Size([1, 1, 240000])


C:\Users\prk\AppData\Local\Temp\ipykernel_18536\256242926.py:2: UserWarning: To copy construct from a tensor, it is recommended to use sourceTensor.clone().detach() or sourceTensor.clone().detach().requires_grad_(True), rather than torch.tensor(sourceTensor).
  waveform = torch.tensor(signal).unsqueeze(0)


In [15]:
# augmentation

# volume up and down
louder = sound + 6
quiter = sound - 6

louder.export('aug_louder.wav', format='wav')
quiter.export('aug_quieter.wav', format='wav')
display(Audio('aug_louder.wav'), Audio('aug_quieter.wav'))

In [17]:
# white noise 
signal, sr = librosa.load(AUDIO_FILE, sr=None)

noise = np.random.normal(0, signal.std(), len(signal))
noisy = signal + noise * 0.5

sf.write('aug_noise.wav', noisy, sr)
display(Audio('aug_noise.wav'))

In [18]:
pitch_up = librosa.effects.pitch_shift(signal, sr=sr, n_steps=4)
pitch_down = librosa.effects.pitch_shift(signal, sr=sr, n_steps=-4)

sf.write('aug_pitch_up.wav', pitch_up, sr)
sf.write('aug_pitch_down.wav', pitch_down, sr)
display(Audio('aug_pitch_up.wav'), Audio('aug_pitch_down.wav'))

In [20]:
# speed up and slow down
faster = librosa.effects.time_stretch(signal, rate=1.5)
slower = librosa.effects.time_stretch(signal, rate=0.7)

sf.write('aug_faster.wav', faster, sr)
sf.write('aug_slower.wav', slower, sr)
display(Audio('aug_faster.wav'), Audio('aug_slower.wav'))

In [21]:
# reverse sound
reversed_sound = sound.reverse()
reversed_sound.export('aug_reverse.wav', format='wav')
display(Audio('aug_reverse.wav'))

In [22]:
# random gain -> random amplitudo audio nya
gain = np.random.uniform(0.5, 2.0)
gained = np.clip(signal * gain, -1, 1)
sf.write('aug_gain.wav', gained, sr)
display(Audio('aug_gain.wav'))

In [23]:
# fade in and fade out
faded = sound.fade_in(2000).fade_out(2000)
faded.export('aug_faded.wav', format='wav')
display(Audio('aug_faded.wav'))